# Physical AI 最終課題：SmolVLAによる複合ロボット操作の評価

## 概要

学習済みAIモデルのSmolVLAを使用し、ロボットに複数の物体操作タスクを実行させる。

シミュレーション環境にはLIBERO-Long（LIBERO-10）を使用する。LIBERO-Longは、物体の移動や収納など、複数の手順を含むロボット操作タスクの評価環境である。

## 目的

- 学習済みSmolVLAによるロボット操作を実際に検証する
- 複数タスクの実行と評価結果の記録を自動化する
- 成功したタスクと失敗したタスクの動作を比較する
- シミュレーションの動作時間を維持して提出用動画を作成する

## 実装方針

SmolVLAは公開済みの学習済みモデルを使用し、追加学習は行わない。

タスクにはLIBERO-Longに用意された既存の作業を使用する。独自に実装する部分は、複数タスクの評価、結果保存、動画生成を一括管理する仕組みである。

成功例だけでなく失敗例も動画に収録し、失敗した段階や原因について考察する。

## 参照:

https://huggingface.co/docs/lerobot/v0.5.1/libero

https://github.com/Lifelong-Robot-Learning/LIBERO/blob/master/libero/libero/benchmark/libero_suite_task_map.py


## 1. 実行環境の準備

本Notebookは、Google ColabのGPUランタイムで実行する。

GPU（Graphics Processing Unit）は、AIモデルの推論に必要な大量の数値計算を高速に処理する装置である。

### 使用ロボット・ソフトウェア

| 項目 | 使用技術 | 役割 |
|---|---|---|
| ロボット | Franka Emika Panda | 7つの関節と2本指のグリッパーを持つロボットアーム |
| AIモデル | SmolVLA | カメラ画像や作業指示などからロボットの行動を予測 |
| 評価環境 | LIBERO-Long（LIBERO-10） | 複数手順を含むロボット操作タスクと成功条件を提供 |
| ロボットシミュレーション | robosuite / MuJoCo | 仮想空間でロボットや物体の動きを再現 |
| AI・評価フレームワーク | LeRobot 0.5.1 | 学習済みモデルの読み込みとタスク評価を実行 |
| AI計算ライブラリ | PyTorch | AIモデルの数値計算を実行 |
| 動画処理 | FFmpeg | 動画の再生時間補正・加工・結合 |
| 実行環境 | Google Colab（GPU） | PythonコードとAI推論を実行 |

今回のロボットは実機ではなく、LIBEROの標準設定で使用されるPandaのシミュレーションモデルである。

SmolVLAは、Vision-Language-Action（視覚・言語・行動）モデルの一種であり、ロボットの観測情報と作業指示から行動を予測する。

追加学習は行わず、公開済みの学習済みモデルを使用する。

### 実行手順

1. Google ColabでNotebookを開き、ランタイムをGPUに設定する
2. 必要なライブラリをインストールする
3. GPUが使用できることを確認する
4. LIBEROのタスク一覧とシミュレータの制御周期を確認する
5. 評価対象のタスクを設定する
6. SmolVLAによるタスク評価を一括実行する
7. 成功・失敗の評価結果と生成された動画を確認する

初回実行では、ライブラリのインストールと学習済みAIモデルの取得に時間がかかる。

### 補足

- LIBEROのタスクには、あらかじめ定義されたロボットの初期状態と成功条件を使用する
- 録画FPSとシミュレータの制御周期が異なる場合は、実際の制御周期に合わせて動画の再生時間を補正する
- 複数タスクの動画は独立した試行を結合したものであり、1回の連続動作ではない


In [1]:
!apt-get update -qq
!apt-get install -y -qq libegl1 libegl1-mesa-dev libgles2-mesa-dev libglfw3 libosmesa6-dev libgl1 ffmpeg
!pip install "lerobot[smolvla,libero]==0.5.1"

W: Skipping acquire of configured file 'main/source/Sources' as repository 'https://r2u.stat.illinois.edu/ubuntu noble InRelease' does not seem to provide it (sources.list entry misspelt?)
Selecting previously unselected package libglx-dev:amd64.
(Reading database ... 127332 files and directories currently installed.)
Preparing to unpack .../00-libglx-dev_1.7.0-1build1_amd64.deb ...
Unpacking libglx-dev:amd64 (1.7.0-1build1) ...
Selecting previously unselected package libgl-dev:amd64.
Preparing to unpack .../01-libgl-dev_1.7.0-1build1_amd64.deb ...
Unpacking libgl-dev:amd64 (1.7.0-1build1) ...
Selecting previously unselected package libegl-dev:amd64.
Preparing to unpack .../02-libegl-dev_1.7.0-1build1_amd64.deb ...
Unpacking libegl-dev:amd64 (1.7.0-1build1) ...
Preparing to unpack .../03-libgl1-mesa-dri_25.2.8-0ubuntu0.24.04.4_amd64.deb ...
Unpacking libgl1-mesa-dri:amd64 (25.2.8-0ubuntu0.24.04.4) over (25.2.8-0ubuntu0.24.04.3) ...
Preparing to unpack .../04-libglx-mesa0_25.2.8-0ubuntu

In [2]:
import importlib.metadata as metadata
import torch

packages = [
    "lerobot",
    "hf-libero",
    "torch",
    "transformers",
    "cuda-python",
    "cuda-bindings",
]

for package in packages:
    print(f"{package}: {metadata.version(package)}")

print("CUDA利用可能:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

lerobot: 0.5.1
hf-libero: 0.1.4
torch: 2.10.0
transformers: 5.3.0
cuda-python: 13.0.3
cuda-bindings: 12.9.4
CUDA利用可能: True
GPU: Tesla T4


In [4]:
!python -m pip check

ipython 7.34.0 requires jedi, which is not installed.
cuda-python 13.0.3 has requirement cuda-bindings~=13.0.3, but you have cuda-bindings 12.9.4.


In [5]:
from libero.libero import benchmark
from lerobot.policies.smolvla.modeling_smolvla import SmolVLAPolicy

suite = benchmark.get_benchmark_dict()["libero_10"]()

print("タスク数:", suite.get_num_tasks())
print("SmolVLAのimport: OK")

Do you want to specify a custom path for the dataset folder? (Y/N): N
Initializing the default config file...
The following information is stored in the config file: /root/.libero/config.yaml
benchmark_root: /usr/local/lib/python3.13/dist-packages/libero/libero
bddl_files: /usr/local/lib/python3.13/dist-packages/libero/libero/./bddl_files
init_states: /usr/local/lib/python3.13/dist-packages/libero/libero/./init_files
datasets: /usr/local/lib/python3.13/dist-packages/libero/libero/../datasets
assets: /usr/local/lib/python3.13/dist-packages/libero/libero/./assets
[info] using task orders [0, 1, 2, 3, 4, 5, 6, 7, 8, 9]
タスク数: 10
SmolVLAのimport: OK



## 2. 利用可能なタスクとシミュレータの制御レートを確認

**Hz（ヘルツ）** は1秒あたりの制御回数。20 Hzなら1ステップのシミュレーション時間は原則0.05秒。`render_fps` は録画用メタデータなので、同じ値とは限らない。両方を表示して確認する。


In [6]:
import importlib.metadata
import os
from pathlib import Path

import torch


# MuJoCoに対して「画像の描画にはEGLを使用する」という設定を渡す
os.environ["MUJOCO_GL"] = "egl"
os.environ["PYOPENGL_PLATFORM"] = "egl"
print("LeRobot:", importlib.metadata.version("lerobot"))
print("CUDA:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))
assert torch.cuda.is_available(), "ColabのGPUランタイムを選んでください"

from libero.libero import benchmark
from lerobot.envs.libero import LiberoEnv

suite = benchmark.get_benchmark_dict()["libero_10"]()
for task_id in range(suite.get_num_tasks()):
    print(f"{task_id}: {suite.get_task(task_id).language}")

# シミュレータを準備する
# LIBEROのロボットシミュレーション環境をLeRobotから利用するためのクラス
env = LiberoEnv(
    task_suite=suite,
    task_id=3,
    task_suite_name="libero_10",
    obs_type="pixels_agent_pos", # 観測データの形式
    control_mode="relative",
    observation_width=256,       # 画像の横幅
    observation_height=256,      # 画像の縦幅
    init_states=True,
    n_envs=1,                    # 環境数
)
print("最大ステップ数:", env._max_episode_steps)
# FPS は Frames Per Second（フレームズ・パー・セカンド）で、動画1秒あたりの画像枚数
print("録画メタデータFPS:", env.metadata.get("render_fps"))

# LeRobotの内部環境から制御周波数を取得
underlying = getattr(getattr(env, "_env", None), "env", None)
control_hz = getattr(underlying, "control_freq", None)
print("シミュレータ制御レート:", control_hz)
env.close()
assert control_hz == 20, "制御周期が20 Hzと確認できません。動画変換前に設定を再確認してください"

LeRobot: 0.5.1
CUDA: True
GPU: Tesla T4


[robosuite WARNING] No private macro file found! (__init__.py:7)
[robosuite WARNING] It is recommended to use a private macro file (__init__.py:8)
[robosuite WARNING] To setup, run: python /usr/local/lib/python3.13/dist-packages/robosuite/scripts/setup_macros.py (__init__.py:9)


[info] using task orders [0, 1, 2, 3, 4, 5, 6, 7, 8, 9]
0: put both the alphabet soup and the tomato sauce in the basket
1: put both the cream cheese box and the butter in the basket
2: turn on the stove and put the moka pot on it
3: put the black bowl in the bottom drawer of the cabinet and close it
4: put the white mug on the left plate and put the yellow and white mug on the right plate
5: pick up the book and place it in the back compartment of the caddy
6: put the white mug on the plate and put the chocolate pudding to the right of the plate
7: put both the alphabet soup and the cream cheese box in the basket
8: put both moka pots on the stove
9: put the yellow and white mug in the microwave and close it
Local assets not found. Downloading from HuggingFace Hub...


/usr/local/lib/python3.13/dist-packages/huggingface_hub/utils/_validators.py:206: UserWarning: The `local_dir_use_symlinks` argument is deprecated and ignored in `snapshot_download`. Downloading to a local directory does not use symlinks anymore.
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 586 files:   0%|          | 0/586 [00:00<?, ?it/s]

Assets downloaded successfully to /root/.cache/libero/assets


/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


最大ステップ数: 520
録画メタデータFPS: 80
シミュレータ制御レート: 20


/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


## 3. スモールスタート：ID 3 を1エピソードだけ実行

`TASK_ID` は `0〜9`。候補は3（ボウル収納）、2（コンロ操作）、9（電子レンジ）。`episode_length=520` は520**ステップ**であり520秒ではない。成功すれば途中で終了する。


In [11]:
import subprocess
from pathlib import Path

TASK_ID = 2
N_EPISODES = 1
MODEL_ID = "HuggingFaceVLA/smolvla_libero"
OUTPUT_DIR = Path(f"/content/libero_long_eval/task_{TASK_ID}")
OUTPUT_DIR.mkdir(parents=True, exist_ok=True)

cmd = [
    "lerobot-eval",
    f"--policy.path={MODEL_ID}",
    "--policy.device=cuda",
    # LIBERO-Longの10種類のタスク群を選ぶ
    "--policy.n_action_steps=10",
    # ロボットのシミュレーション環境としてLIBEROを設定
    "--env.type=libero",
    "--env.task=libero_10",
    f"--env.task_ids=[{TASK_ID}]",
    "--env.control_mode=relative",
    "--env.episode_length=520",
    "--env.fps=20",
    "--env.max_parallel_tasks=1",
    "--eval.n_episodes=1",
    "--eval.batch_size=1",
    "--eval.use_async_envs=false",
    "--seed=42",
    f"--output_dir={OUTPUT_DIR}",
]
print("実行するコマンド:", " ".join(cmd))
subprocess.run(cmd, env=os.environ.copy(), check=True)
print("保存場所:", OUTPUT_DIR)

実行するコマンド: lerobot-eval --policy.path=HuggingFaceVLA/smolvla_libero --policy.device=cuda --policy.n_action_steps=10 --env.type=libero --env.task=libero_10 --env.task_ids=[2] --env.control_mode=relative --env.episode_length=520 --env.fps=20 --env.max_parallel_tasks=1 --eval.n_episodes=1 --eval.batch_size=1 --eval.use_async_envs=false --seed=42 --output_dir=/content/libero_long_eval/task_2


/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


保存場所: /content/libero_long_eval/task_2


In [23]:
import inspect

from libero.libero.envs.env_wrapper import ControlEnv

# inspect.getfile: クラスが定義されているPythonファイルを調べる
print("定義ファイル:", inspect.getfile(ControlEnv))

# inspect.signature: __init__が受け取る引数と標準値を調べる
print("初期化引数:", inspect.signature(ControlEnv.__init__))

# robots引数の標準値だけを取り出す
parameters = inspect.signature(ControlEnv.__init__).parameters
print("標準ロボット:", parameters["robots"].default)


定義ファイル: /usr/local/lib/python3.13/dist-packages/libero/libero/envs/env_wrapper.py
初期化引数: (self, bddl_file_name, robots=['Panda'], controller='OSC_POSE', gripper_types='default', initialization_noise=None, use_camera_obs=True, has_renderer=False, has_offscreen_renderer=True, render_camera='frontview', render_collision_mesh=False, render_visual_mesh=True, render_gpu_device_id=-1, control_freq=20, horizon=1000, ignore_done=False, hard_reset=True, camera_names=['agentview', 'robot0_eye_in_hand'], camera_heights=128, camera_widths=128, camera_depths=False, camera_segmentations=None, renderer='mujoco', renderer_config=None, **kwargs)
標準ロボット: ['Panda']


## 4. 結果を確認：成功・MP4のFPS・動画長・シミュレーション時間

LeRobot 0.5.1では録画FPSが80で、実際の制御周期20 Hzと不一致の場合がある。ここではMP4の**フレーム数**と**FPS**を別々に取得する。壁時計時間（Colabが計算にかかった実時間）は動画の動作時間ではない。


In [12]:
import json
from fractions import Fraction
from IPython.display import Video, display


def video_info(path: Path) -> dict:
    """
    MP4のフレームレート、フレーム数、長さを取得する関数

    Args:
        path: 調査する動画のパス

    Returns:
        フレームレート、フレーム数、長さを含む辞書
    """
    completed = subprocess.run(
        ["ffprobe", "-v", "error", "-select_streams", "v:0", "-count_frames",
         "-show_entries", "stream=avg_frame_rate,nb_read_frames,duration",
         "-of", "json", str(path)],
        capture_output=True, text=True, check=True,
    )
    video_stream = json.loads(completed.stdout)["streams"][0]
    fps = float(Fraction(video_stream["avg_frame_rate"]))
    frames = int(video_stream["nb_read_frames"])
    return {"fps": fps, "frames": frames, "mp4_seconds": float(video_stream["duration"])}

videos = sorted(OUTPUT_DIR.rglob("*.mp4"))
assert videos, "動画が見つかりません。評価ログとoutput_dirを確認してください"
for path in videos:
    info = video_info(path)
    sim_seconds = info["frames"] / control_hz
    print(f"{path.name}: {info['frames']}枚, MP4 {info['fps']}FPS / {info['mp4_seconds']:.2f}秒")
    print(f"シミュレーション時間の見積もり: {sim_seconds:.2f}秒 ({control_hz}Hz)")
    display(Video(str(path), embed=True, width=480))

metrics_path = OUTPUT_DIR / "eval_info.json"
if metrics_path.exists():
    metrics = json.loads(metrics_path.read_text(encoding="utf-8"))
    print("評価JSONのトップレベルキー:", list(metrics))
    print("成功判定はeval_info.jsonのper_task / per_episode / successes等を確認してください")
else:
    print("eval_info.jsonが見つかりません。評価ログを確認してください")

eval_episode_0.mp4: 520枚, MP4 80.0FPS / 6.50秒
シミュレーション時間の見積もり: 26.00秒 (20Hz)


/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


評価JSONのトップレベルキー: ['per_task', 'per_group', 'overall']
成功判定はeval_info.jsonのper_task / per_episode / successes等を確認してください


## 5. 20 Hzの動作時間に合わせた動画を出力

80 FPSでエンコードされた1ステップ1フレームの録画は、20 Hz制御と比べて4倍速で再生されるため、タイムスタンプを補正する。**これは60秒への尺合わせではない。** 元動画がすでに20 FPSなら補正しない。

例：400フレームは20 Hzなら20秒だが、80 FPS MP4では5秒。補正後は400フレーム・20 FPS・20秒となる。


In [13]:
from math import isclose

sim_videos = []
for source in videos:
    info = video_info(source)
    target = source.with_name(source.stem + "_simtime20fps.mp4")
    ratio = info["fps"] / float(control_hz)
    if isclose(ratio, 1.0, abs_tol=0.01):
        print("既に制御周期と一致:", source)
        sim_videos.append(source)
        continue
    if not isclose(ratio, 4.0, abs_tol=0.01):
        raise RuntimeError(f"想定外の録画FPS: {info['fps']}。動画の変換を中断します")
    subprocess.run(
        ["ffmpeg", "-y", "-v", "error", "-i", str(source),
         "-vf", "setpts=4*(PTS-STARTPTS)", "-r", "20",
         "-c:v", "libx264", "-pix_fmt", "yuv420p", "-an", str(target)],
        check=True,
    )
    corrected = video_info(target)
    print("補正後:", target, corrected)
    assert abs(corrected["frames"] - info["frames"]) <= 1, "フレーム数が大きく変化しました"
    sim_videos.append(target)

for path in sim_videos:
    display(Video(str(path), embed=True, width=480))

補正後: /content/libero_long_eval/task_2/videos/libero_10_2/eval_episode_0_simtime20fps.mp4 {'fps': 20.0, 'frames': 520, 'mp4_seconds': 26.0}


/usr/local/lib/python3.13/dist-packages/jupyter_client/session.py:203: DeprecationWarning: datetime.datetime.utcnow() is deprecated and scheduled for removal in a future version. Use timezone-aware objects to represent datetimes in UTC: datetime.datetime.now(datetime.UTC).
  return datetime.utcnow().replace(tzinfo=utc)


## 6. 判定・次のタスク

最初のID 3が **実際に動作し、途中で成果が見えるか**を確認する。次は `TASK_ID=2` と `9` を実行。各候補を3エピソード程度評価して再現性を確かめ、成功した作業時間を合計する。

記録する項目：タスクID、初期条件・seed、成功（true/false）、ステップ数、シミュレーション秒数、MP4秒数、手先が実際に動いた範囲、目視で確認できた達成段階、失敗要因。タスクが失敗した長い停滞時間は「意味のある動作時間」に数えない。

**提出動画60秒に達しない場合**：別タスクを追加し、実際に動作させる。等速より遅くしたり同じフレームを繰り返したりしない。最終的に独立エピソードをつなぐ場合は、独立した試行の連結であることを明示する。


In [10]:
import json
from pathlib import Path

metrics_path = Path("/content/libero_long_eval/task_3/eval_info.json")

if metrics_path.exists():
    metrics = json.loads(metrics_path.read_text(encoding="utf-8"))
    print(json.dumps(metrics, indent=2, ensure_ascii=False))
else:
    print("評価結果のJSONファイルが見つかりません")

{
  "per_task": [
    {
      "task_group": "libero_10",
      "task_id": 3,
      "metrics": {
        "sum_rewards": [
          1.0
        ],
        "max_rewards": [
          1.0
        ],
        "successes": [
          true
        ],
        "video_paths": [
          "/content/libero_long_eval/task_3/videos/libero_10_3/eval_episode_0.mp4"
        ]
      }
    }
  ],
  "per_group": {
    "libero_10": {
      "avg_sum_reward": 1.0,
      "avg_max_reward": 1.0,
      "pc_success": 100.0,
      "n_episodes": 1,
      "video_paths": [
        "/content/libero_long_eval/task_3/videos/libero_10_3/eval_episode_0.mp4"
      ]
    }
  },
  "overall": {
    "avg_sum_reward": 1.0,
    "avg_max_reward": 1.0,
    "pc_success": 100.0,
    "n_episodes": 1,
    "eval_s": 98.45463848114014,
    "eval_ep_s": 98.45464015007019,
    "video_paths": [
      "/content/libero_long_eval/task_3/videos/libero_10_3/eval_episode_0.mp4"
    ]
  }
}


## 7. 最終版コード




### 7.1 プログラムの設計

複数のタスクを一括評価するため、処理を役割ごとにクラスへ分割する。

#### データの定義

Pythonの`dataclass`を使って、タスクの内容、実行設定、動画情報、評価結果を表現する。

#### ロボットの評価

`LeRobotEvaluator`がSmolVLAによる推論、シミュレーション実行、成功判定の取得を担当する。

#### 動画の処理

`VideoService`が録画のフレーム数・再生速度の確認、動画の加工と結合を担当する。

#### 評価結果の保存

`ResultRepository`が実行結果をCSVとJSONで保存する。

#### 処理全体の管理

`EvaluationPipeline`が各クラスを呼び出し、タスクの評価から完成動画の出力までを順番に実行する。

この設計により、評価処理と動画処理を分離し、タスクの追加や表示方法の変更を行いやすくする。



In [19]:
import csv
import json
import os
import subprocess
import warnings
from dataclasses import asdict, dataclass
from fractions import Fraction
from pathlib import Path

from IPython.display import Video, display

# jupyter_client由来の特定のDeprecationWarningだけを非表示にする
warnings.filterwarnings(
    "ignore",
    category=DeprecationWarning,
    message=r"datetime\.datetime\.utcnow\(\) is deprecated.*",
    module=r"jupyter_client\.session",
)


# ============================================================
# 1. ドメイン層：タスク・設定・結果のデータ構造
# ============================================================

@dataclass(frozen=True)
class TaskSpec:
    task_id: int
    name: str


@dataclass(frozen=True)
class AppConfig:
    tasks: tuple[TaskSpec, ...]
    root: Path = Path("/content/libero_long_eval")
    model_id: str = "HuggingFaceVLA/smolvla_libero"
    control_hz: int = 20
    max_steps: int = 520
    seed: int = 42
    reuse_existing: bool = True
    include_failed: bool = True


@dataclass(frozen=True)
class VideoInfo:
    fps: float
    frames: int
    seconds: float


@dataclass(frozen=True)
class TaskResult:
    task_id: int
    name: str
    status: str
    sim_seconds: float = 0.0
    frames: int = 0
    included: bool = False
    video: str = ""
    error: str = ""


# ============================================================
# 2. 外部連携層：LeRobotでロボットを評価
# ============================================================

class LeRobotEvaluator:
    def __init__(self, config: AppConfig):
        self.config = config

    def evaluate(self, task: TaskSpec) -> tuple[bool, Path]:
        output = self.config.root / f"task_{task.task_id}"
        info_path = output / "eval_info.json"

        # 同じ設定で実行した既存結果を再利用
        if self.config.reuse_existing and info_path.exists():
            cached = json.loads(info_path.read_text(encoding="utf-8"))
            record = cached["per_task"][0]
            videos = record["metrics"]["video_paths"]

            if record["task_id"] == task.task_id and len(videos) == 1:
                source = Path(videos[0])
                if source.is_file():
                    print(f"[再利用] ID {task.task_id}", flush=True)
                    return bool(record["metrics"]["successes"][0]), source

        output.mkdir(parents=True, exist_ok=True)

        # MuJoCoの描画設定を評価プロセスへ引き継ぐ
        env = os.environ.copy()
        env.update(MUJOCO_GL="egl", PYOPENGL_PLATFORM="egl")

        cmd = [
            "lerobot-eval",
            f"--policy.path={self.config.model_id}",
            "--policy.device=cuda",
            "--policy.n_action_steps=10",
            "--env.type=libero",
            "--env.task=libero_10",
            f"--env.task_ids=[{task.task_id}]",
            "--env.control_mode=relative",
            f"--env.episode_length={self.config.max_steps}",
            f"--env.fps={self.config.control_hz}",
            "--env.max_parallel_tasks=1",
            "--eval.n_episodes=1",
            "--eval.batch_size=1",
            "--eval.use_async_envs=false",
            f"--seed={self.config.seed}",
            f"--output_dir={output}",
        ]

        print(f"[推論開始] ID {task.task_id}: {task.name}", flush=True)

        # 別プロセスでAI推論・シミュレーション・録画を実行
        subprocess.run(cmd, env=env, check=True)

        result = json.loads(info_path.read_text(encoding="utf-8"))
        record = result["per_task"][0]

        assert record["task_id"] == task.task_id
        assert len(record["metrics"]["successes"]) == 1

        success = bool(record["metrics"]["successes"][0])
        source = Path(record["metrics"]["video_paths"][0])
        return success, source


# ============================================================
# 3. 外部連携層：動画情報・時間補正・結合
# ============================================================

class VideoService:
    FONT = "/usr/share/fonts/truetype/dejavu/DejaVuSans-Bold.ttf"

    def __init__(self, config: AppConfig):
        self.config = config

    def inspect(self, path: Path) -> VideoInfo:
        # ffprobeでMP4のFPS・フレーム数・再生時間を取得
        result = subprocess.run(
            [
                "ffprobe", "-v", "error",
                "-select_streams", "v:0",
                "-count_frames",
                "-show_entries",
                "stream=avg_frame_rate,nb_read_frames,duration",
                "-of", "json",
                str(path),
            ],
            capture_output=True,
            text=True,
            check=True,
        )

        stream = json.loads(result.stdout)["streams"][0]
        fps = float(Fraction(stream["avg_frame_rate"]))
        frames = int(stream["nb_read_frames"])
        seconds = float(stream.get("duration") or frames / fps)
        return VideoInfo(fps=fps, frames=frames, seconds=seconds)

    def render(
        self,
        task: TaskSpec,
        success: bool,
        source: Path,
    ) -> tuple[Path, VideoInfo]:
        original = self.inspect(source)

        # 検証済みの20Hz相当・80FPS録画だけを処理
        valid_fps = (
            self.config.control_hz,
            self.config.control_hz * 4,
        )
        if not any(abs(original.fps - fps) < 0.1 for fps in valid_fps):
            raise ValueError(f"想定外の録画FPS: {original.fps}")

        speed = original.fps / self.config.control_hz
        status = "SUCCESS" if success else "FAILED"

        clips_dir = self.config.root / "clips"
        clips_dir.mkdir(parents=True, exist_ok=True)
        target = clips_dir / f"task_{task.task_id}_labeled.mp4"

        # ロボット映像を中央に配置し、結果の1行だけを表示
        # setptsは1ステップ1フレームを前提に制御周期へ整合
        filters = ",".join([
            f"setpts={speed:.6g}*(PTS-STARTPTS)",
            "scale=1280:720:force_original_aspect_ratio=decrease",
            "pad=1280:720:(ow-iw)/2:(oh-ih)/2:color=0x101827",
            (
                f"drawtext=fontfile={self.FONT}:"
                f"text='TASK {task.task_id:02d}  {status}':"
                "x=30:y=30:fontsize=28:fontcolor=white:"
                "box=1:boxcolor=black@0.55"
            ),
        ])

        subprocess.run(
            [
                "ffmpeg", "-y", "-v", "error",
                "-i", str(source),
                "-vf", filters,
                "-r", str(self.config.control_hz),
                "-c:v", "libx264",
                "-preset", "veryfast",
                "-crf", "21",
                "-pix_fmt", "yuv420p",
                "-an",
                str(target),
            ],
            check=True,
        )

        # 動画の速度補正でフレームが失われていないか検査
        converted = self.inspect(target)
        if abs(converted.frames - original.frames) > 1:
            raise RuntimeError("動画の変換でフレーム数が変化しました")

        return target, original

    def combine(self, clips: list[Path]) -> Path:
        # FFmpegのconcat機能で複数動画を順番に結合
        manifest = self.config.root / "concat.txt"
        manifest.write_text(
            "".join(f"file '{path.resolve()}'\n" for path in clips),
            encoding="utf-8",
        )

        final = self.config.root / "PAI_LIBERO_Long_1x_montage.mp4"
        subprocess.run(
            [
                "ffmpeg", "-y", "-v", "error",
                "-f", "concat",
                "-safe", "0",
                "-i", str(manifest),
                "-c", "copy",
                "-movflags", "+faststart",
                str(final),
            ],
            check=True,
        )
        return final


# ============================================================
# 4. 外部連携層：CSV・JSONへの保存
# ============================================================

class ResultRepository:
    def __init__(self, root: Path):
        self.root = root

    def save(self, results: list[TaskResult]) -> None:
        # asdictでdataclassから辞書へ変換
        records = [asdict(item) for item in results]

        json_path = self.root / "task_summary.json"
        json_path.write_text(
            json.dumps(records, ensure_ascii=False, indent=2),
            encoding="utf-8",
        )

        csv_path = self.root / "task_summary.csv"
        with csv_path.open(
            "w",
            encoding="utf-8-sig",
            newline="",
        ) as file:
            writer = csv.DictWriter(
                file,
                fieldnames=list(records[0]),
            )
            writer.writeheader()
            writer.writerows(records)


# ============================================================
# 5. アプリケーション層：処理全体を管理
# ============================================================

class EvaluationPipeline:
    def __init__(self, config: AppConfig):
        self.config = config
        self.evaluator = LeRobotEvaluator(config)
        self.video = VideoService(config)
        self.repository = ResultRepository(config.root)

    def run(self) -> None:
        tasks = self.config.tasks

        if not tasks:
            raise ValueError("タスクが指定されていません")
        if len({task.task_id for task in tasks}) != len(tasks):
            raise ValueError("タスクIDが重複しています")
        if any(not 0 <= task.task_id <= 9 for task in tasks):
            raise ValueError("libero_10のIDは0〜9です")

        self.config.root.mkdir(parents=True, exist_ok=True)
        results: list[TaskResult] = []
        clips: list[Path] = []

        for task in tasks:
            try:
                # ロボットを動かし、評価結果と動画を取得
                success, source = self.evaluator.evaluate(task)

                # 動画を正しい時間で再生できるよう変換
                clip, info = self.video.render(task, success, source)

                # 失敗動画を含めるかどうかのルール
                included = success or self.config.include_failed
                if included:
                    clips.append(clip)

                row = TaskResult(
                    task_id=task.task_id,
                    name=task.name,
                    status="SUCCESS" if success else "FAILED",
                    sim_seconds=round(
                        info.frames / self.config.control_hz,
                        2,
                    ),
                    frames=info.frames,
                    included=included,
                    video=str(clip),
                )
            except Exception as error:
                # 1件エラーでも、残りのタスクの評価は続行
                row = TaskResult(
                    task_id=task.task_id,
                    name=task.name,
                    status="ERROR",
                    error=str(error),
                )

            results.append(row)
            print(
                f"[結果] ID {task.task_id}: "
                f"{row.status} / {row.sim_seconds:.2f}秒",
                flush=True,
            )
            if row.error:
                print("  原因:", row.error)

        # 評価結果を保存
        self.repository.save(results)

        print("\n=== 評価一覧 ===")
        for row in results:
            print(
                f"ID {row.task_id}: "
                f"{row.status} / {row.sim_seconds:.2f}秒"
            )

        if not clips:
            print("結合できる動画がありません")
            return

        # 採用した動画を結合
        final = self.video.combine(clips)
        info = self.video.inspect(final)

        print("\n=== 完成動画 ===")
        print("保存先:", final)
        print(f"長さ: {info.seconds:.2f}秒")
        print(f"FPS: {info.fps}")
        print(f"フレーム数: {info.frames}")
        print("CSV:", self.config.root / "task_summary.csv")

        if info.seconds < 60:
            print(f"60秒まであと約{60 - info.seconds:.2f}秒")
        if info.seconds > 180:
            print("提出条件の3分を超えています")

        print("※独立したエピソードを結合した動画です")
        display(Video(str(final), embed=True, width=760))


### 7.2. 評価タスクと実行条件

本課題では、LIBERO-Longのタスクから以下の5種類を選定する。

| ID | タスク内容 |
|---|---|
| 3 | ボウルを引き出しに収納し、閉じる |
| 2 | コンロをつけ、モカポットを置く |
| 9 | マグカップを電子レンジに収納し、閉じる |
| 0 | スープ缶とトマトソースをかごへ入れる |
| 1 | クリームチーズとバターをかごへ入れる |

### 評価条件

- AIモデル：HuggingFaceVLA/smolvla_libero
- 評価環境：libero_10
- 制御周期：20 Hz
- 最大実行ステップ数：520
- 乱数シード：42
- 各タスクの試行回数：1回
- 成功・失敗の両方を動画に収録する

`reuse_existing=True`の場合、保存済みの評価結果と動画を再利用する。

評価条件を変更して新しく検証する場合は、過去の結果との混在を防ぐため、保存先を分けて再評価する。


In [20]:
# ============================================================
# 6. 実行設定：ここだけ変更する
# ============================================================

CONFIG = AppConfig(
    tasks=(
        TaskSpec(3, "ボウル収納"),
        TaskSpec(2, "コンロ操作"),
        TaskSpec(9, "電子レンジ収納"),
        TaskSpec(0, "食品2つをかごへ収納"),
        TaskSpec(1, "チーズとバターをかごへ収納"),
    ),
    reuse_existing=True,
    include_failed=True,
)


### 7.3. 一括評価の実行

指定されたタスクを順番に評価し、成功判定と動作動画を取得する。

評価が完了すると、以下のファイルが生成される。

- `task_summary.csv`：タスクごとの評価結果
- `task_summary.json`：評価結果のJSON形式データ
- `clips/`：タスクごとに加工した動画
- `PAI_LIBERO_Long_1x_montage.mp4`：複数タスクを結合した提出用動画

録画された各フレームが1制御ステップに対応する前提で、録画FPSと制御周期の違いを補正する。

動画の長さを増やすためのスロー再生や同一フレームの繰り返しは行わない。

また、動画はそれぞれ独立して実行したタスクを結合したものであり、1回の連続動作ではない。



In [21]:
EvaluationPipeline(CONFIG).run()

[再利用] ID 3
[結果] ID 3: SUCCESS / 10.90秒
[再利用] ID 2
[結果] ID 2: FAILED / 26.00秒
[再利用] ID 9
[結果] ID 9: SUCCESS / 15.05秒
[再利用] ID 0
[結果] ID 0: SUCCESS / 25.95秒
[再利用] ID 1
[結果] ID 1: SUCCESS / 12.35秒

=== 評価一覧 ===
ID 3: SUCCESS / 10.90秒
ID 2: FAILED / 26.00秒
ID 9: SUCCESS / 15.05秒
ID 0: SUCCESS / 25.95秒
ID 1: SUCCESS / 12.35秒

=== 完成動画 ===
保存先: /content/libero_long_eval/PAI_LIBERO_Long_1x_montage.mp4
長さ: 90.25秒
FPS: 20.0
フレーム数: 1805
CSV: /content/libero_long_eval/task_summary.csv
※独立したエピソードを結合した動画です



## 7.4. 評価結果と考察

各タスクを1回ずつ評価した結果、5タスク中4タスクが成功し、1タスクが失敗した。

| ID | タスク | 結果 |
|---|---|---|
| 3 | ボウル収納 | 成功 |
| 2 | コンロ操作とモカポット配置 | 失敗 |
| 9 | 電子レンジへの収納 | 成功 |
| 0 | スープ缶とトマトソースの収納 | 成功 |
| 1 | クリームチーズとバターの収納 | 成功 |

### 成功例

ボウルや食品の収納など、複数の手順を含む作業で成功判定が得られた。

### 失敗例

コンロをつけてモカポットを置くタスクでは、最終的な成功条件を満たさなかった。

動画を確認すると、コンロ操作までは進んだ可能性があるが、モカポットを所定の位置へ移動する作業は完了していなかった。

ただし、内部状態を調べたわけではないため、詳細な失敗原因は確定していない。

### 評価上の制約

今回は各タスク1回のみ実行したため、モデルの安定した成功率を測定したものではない。

今後は試行回数を増やし、初期条件の変化や失敗原因について、より詳しく検証したい。


In [22]:
# 提出前の最終チェック
summary_path = CONFIG.root / "task_summary.json"
video_path = CONFIG.root / "PAI_LIBERO_Long_1x_montage.mp4"

# JSON形式の評価結果を読み込む
results = json.loads(summary_path.read_text(encoding="utf-8"))

# 指定したタスクがすべて記録されていることを確認
expected_ids = {task.task_id for task in CONFIG.tasks}
actual_ids = {row["task_id"] for row in results}
assert actual_ids == expected_ids, "評価結果のタスクIDが一致しません"

# 実行エラーがなく、成功・失敗の両方が収録されていることを確認
assert all(
    row["status"] in ("SUCCESS", "FAILED")
    for row in results
), "未完了またはエラーになったタスクがあります"
assert all(row["included"] for row in results), "動画から除外されたタスクがあります"

# 提出動画の長さが60〜180秒であることを確認
info = VideoService(CONFIG).inspect(video_path)
assert 60 <= info.seconds <= 180, "提出動画が1〜3分の範囲外です"

print("提出前チェック: OK")
print(f"評価タスク数: {len(results)}")
print(f"動画時間: {info.seconds:.2f}秒")
print(f"動画FPS: {info.fps}")
print("完成動画:", video_path)

display(Video(str(video_path), embed=True, width=760))


提出前チェック: OK
評価タスク数: 5
動画時間: 90.25秒
動画FPS: 20.0
完成動画: /content/libero_long_eval/PAI_LIBERO_Long_1x_montage.mp4
